In [1]:
import os, json, shutil
from pathlib import Path
import numpy as np
import nibabel as nib
import pandas as pd
from tqdm import tqdm
import torch
import nnunetv2 as _nnunetv2_pkg

# TEACHER: modelo robusto treinado (Modified_nnUNet_submission, Dataset 999)
TEACHER_BASE = Path("/home/henrique.grande/brats_goat_experiments/models_configs/nnUnet_modified_sub")
os.environ["nnUNet_raw"] = str(TEACHER_BASE / "nnUNet_raw")
os.environ["nnUNet_preprocessed"] = str(TEACHER_BASE / "nnUNet_preprocessed")
os.environ["nnUNet_results"] = str(TEACHER_BASE / "nnUNet_results")

DATASET_ID = 999
DATASET_NAME = "BraTS-GoAT-modified-sub"
PLANS_NAME = "nnUNetResEncUNetLPlans"
TRAINER    = "nnUNetTrainer_250epochs_Modified"
CONFIG     = "3d_fullres"
FOLDS_STR  = "0 1 2 3 4"               # ensemble dos 5 folds
CHK        = "checkpoint_best.pth"     # usar o melhor

# ENTRADA: pool nao-rotulado
UNLABELED_RAW = Path("/home/henrique.grande/brats_goat_experiments/data/raw/MICCAI2024-BraTS-GoAT-TrainingData-WithOut-GroundTruth")

# SAIDA: pasta pseudolabeled consumida pelo Modified_nnUNet_semisupervised_submission
OUT_PSEUDO = Path("/home/henrique.grande/brats_goat_experiments/data/raw/MICCAI2024-BraTS-GoAT-TrainingData-Without-GroundTruth-pseudolabeled")

# Area de trabalho do gerador (input nnU-Net + predicoes)
GEN_BASE = Path("/home/henrique.grande/brats_goat_experiments/models_configs/modified_pseudolabel_generator")
GEN_IMAGES = GEN_BASE / "imagesUnlabeled"
GEN_PRED   = GEN_BASE / "pseudo_pred"
for p in [GEN_IMAGES, GEN_PRED, OUT_PSEUDO]:
    p.mkdir(parents=True, exist_ok=True)

MODS = ["t1n", "t1c", "t2w", "t2f"]
FILE_ENDING = ".nii.gz"

print("Teacher results :", os.environ["nnUNet_results"])
print("Pool nao-rotulado:", UNLABELED_RAW, "| existe:", UNLABELED_RAW.exists())
print("Saida pseudolabeled:", OUT_PSEUDO)

Teacher results : /home/henrique.grande/brats_goat_experiments/models_configs/nnUnet_modified_sub/nnUNet_results
Pool nao-rotulado: /home/henrique.grande/brats_goat_experiments/data/raw/MICCAI2024-BraTS-GoAT-TrainingData-WithOut-GroundTruth | existe: True
Saida pseudolabeled: /home/henrique.grande/brats_goat_experiments/data/raw/MICCAI2024-BraTS-GoAT-TrainingData-Without-GroundTruth-pseudolabeled


In [2]:
# Limpeza: apaga a saida (OUT_PSEUDO) e as predicoes (GEN_PRED)
for p in [OUT_PSEUDO, GEN_PRED]:
    if p.exists():
        shutil.rmtree(p)
    p.mkdir(parents=True, exist_ok=True)
print("Pastas limpas e recriadas:")
print("  OUT_PSEUDO:", OUT_PSEUDO)
print("  GEN_PRED  :", GEN_PRED)

Pastas limpas e recriadas:
  OUT_PSEUDO: /home/henrique.grande/brats_goat_experiments/data/raw/MICCAI2024-BraTS-GoAT-TrainingData-Without-GroundTruth-pseudolabeled
  GEN_PRED  : /home/henrique.grande/brats_goat_experiments/models_configs/modified_pseudolabel_generator/pseudo_pred


In [3]:
print("=" * 60)
print("  Informacoes da GPU")
print("=" * 60)
if torch.cuda.is_available():
    props = torch.cuda.get_device_properties(0)
    print("  CUDA   :", torch.version.cuda, "| PyTorch:", torch.__version__)
    print("  GPU    :", props.name)
    print("  VRAM   :", f"{props.total_memory/1e9:.2f} GB")
else:
    print("  CUDA   : NAO")
print("=" * 60)

  Informacoes da GPU


  CUDA   : 12.1 | PyTorch: 2.5.1+cu121
  GPU    : NVIDIA H100 80GB HBM3
  VRAM   : 85.02 GB


In [4]:
# Trainer customizado: nnUNetTrainer_250epochs_Modified

_MODIFIED_TRAINER_SRC = r"""
import torch
import torch.nn as nn
import torch.nn.functional as F
import numpy as np
from scipy.ndimage import distance_transform_edt

from nnunetv2.training.nnUNetTrainer.variants.training_length.nnUNetTrainer_Xepochs import nnUNetTrainer_250epochs

# 1. GROUPNORM

class GroupNormWrapper(nn.GroupNorm):
    def __init__(self, num_features, eps=1e-5, affine=True, **kwargs):
        if num_features >= 8:
            num_groups = 8
        else:
            num_groups = max(1, num_features // 2)
        super().__init__(num_groups=num_groups, num_channels=num_features,
                         eps=eps, affine=affine)


def replace_norms_with_groupnorm(module):
    count = 0
    for name, child in module.named_children():
        if isinstance(child, (
            nn.InstanceNorm1d, nn.InstanceNorm2d, nn.InstanceNorm3d,
            nn.BatchNorm1d,    nn.BatchNorm2d,    nn.BatchNorm3d,
        )):
            num_features = child.num_features
            setattr(module, name, GroupNormWrapper(num_features))
            count += 1
        else:
            count += replace_norms_with_groupnorm(child)
    return count


# 3. AXIAL ATTENTION 3D (no decoder)

class AxialAttention3D(nn.Module):
    def __init__(self, channels, num_heads=4):
        super().__init__()
        while channels % num_heads != 0 and num_heads > 1:
            num_heads -= 1
        self.attn_d = nn.MultiheadAttention(channels, num_heads, batch_first=True)
        self.attn_h = nn.MultiheadAttention(channels, num_heads, batch_first=True)
        self.attn_w = nn.MultiheadAttention(channels, num_heads, batch_first=True)
        self.norm = GroupNormWrapper(channels)

    def forward(self, x):
        B, C, D, H, W = x.shape
        xd = x.permute(0, 3, 4, 2, 1).contiguous().view(B*H*W, D, C)
        xd, _ = self.attn_d(xd, xd, xd)
        xd = xd.view(B, H, W, D, C).permute(0, 4, 3, 1, 2).contiguous()
        xh = x.permute(0, 2, 4, 3, 1).contiguous().view(B*D*W, H, C)
        xh, _ = self.attn_h(xh, xh, xh)
        xh = xh.view(B, D, W, H, C).permute(0, 4, 1, 3, 2).contiguous()
        xw = x.permute(0, 2, 3, 4, 1).contiguous().view(B*D*H, W, C)
        xw, _ = self.attn_w(xw, xw, xw)
        xw = xw.view(B, D, H, W, C).permute(0, 4, 1, 2, 3).contiguous()
        return self.norm(x + xd + xh + xw)


class StageWithAttention(nn.Module):
    def __init__(self, stage, attn):
        super().__init__()
        self.stage = stage
        self.attn = attn

    def forward(self, x):
        out = self.stage(x)
        if out.dim() == 5:
            return self.attn(out)
        return out


def inject_axial_attention_in_decoder(model):
    if not hasattr(model, "decoder") or not hasattr(model.decoder, "stages"):
        return False
    if len(model.decoder.stages) == 0:
        return False
    target_idx = 0  # primeiro stage do decoder = menor resolucao (logo apos o bottleneck)
    dec_stage = model.decoder.stages[target_idx]
    out_channels = None
    for m in dec_stage.modules():
        if isinstance(m, nn.Conv3d):
            out_channels = m.out_channels
    if out_channels is None:
        return False
    attn = AxialAttention3D(out_channels, num_heads=4)
    model.decoder.stages[target_idx] = StageWithAttention(dec_stage, attn)
    return True


# 4. HD LOSS

class HausdorffDTLoss(nn.Module):
    def __init__(self, alpha=2.0):
        super().__init__()
        self.alpha = alpha

    @staticmethod
    @torch.no_grad()
    def _dt_batch(mask):
        np_mask = (mask.detach().cpu().numpy() > 0.5).astype(bool)
        out = np.zeros(np_mask.shape, dtype=np.float32)
        if np_mask.ndim == 5:
            for b in range(np_mask.shape[0]):
                for c in range(np_mask.shape[1]):
                    fg = np_mask[b, c]
                    if fg.any() and not fg.all():
                        out[b, c] = distance_transform_edt(~fg)
        return torch.from_numpy(out).to(mask.device)

    def forward(self, pred_prob, target_bin):
        if target_bin.dtype != torch.float32:
            target_bin = target_bin.float()
        dt_gt = self._dt_batch(target_bin)
        dt_pr = self._dt_batch(pred_prob)
        err = (pred_prob - target_bin) ** 2
        weight = dt_gt.pow(self.alpha) + dt_pr.pow(self.alpha)
        return (err * weight).mean()


class DC_BCE_HD_Loss(nn.Module):
    def __init__(self, base_loss, hd_lambda=0.05, hd_warmup_epochs=10,
                 hd_every_n_steps=5):
        super().__init__()
        self.base_loss = base_loss
        self.hd_loss = HausdorffDTLoss(alpha=2.0)
        self.hd_lambda = hd_lambda
        self.hd_warmup_epochs = hd_warmup_epochs
        self.hd_every_n_steps = hd_every_n_steps
        self.current_epoch = 0
        self._step = 0

    def set_epoch(self, e):
        self.current_epoch = e

    def forward(self, logits, target):
        base = self.base_loss(logits, target)
        self._step += 1
        if self.current_epoch < self.hd_warmup_epochs:
            return base
        if self._step % self.hd_every_n_steps != 0:
            return base
        if isinstance(logits, list):
            logits_full = logits[0]
            target_full = target[0] if isinstance(target, list) else target
        else:
            logits_full = logits
            target_full = target
        pred_prob = torch.sigmoid(logits_full)
        hd = self.hd_loss(pred_prob, target_full)
        return base + self.hd_lambda * hd


# Trainer

class nnUNetTrainer_250epochs_Modified(nnUNetTrainer_250epochs):

    @staticmethod
    def build_network_architecture(*args, **kwargs):
        network = nnUNetTrainer_250epochs.build_network_architecture(*args, **kwargs)
        n = replace_norms_with_groupnorm(network)
        injected = inject_axial_attention_in_decoder(network)
        print(f"[Modified] build_network_architecture: GroupNorm={n} | AxialAttn_decoder={injected}")
        return network

    def _build_loss(self):
        base_loss = super()._build_loss()
        compound = DC_BCE_HD_Loss(base_loss, hd_lambda=0.05,
                                  hd_warmup_epochs=10, hd_every_n_steps=5)
        if self.local_rank == 0:
            print("[Modified] Loss: DC+BCE region-based + 0.05*HD (warmup=10, every=5 steps)")
        return compound

    def on_train_epoch_start(self):
        super().on_train_epoch_start()
        if hasattr(self.loss, "set_epoch"):
            self.loss.set_epoch(self.current_epoch)
"""

_nnunet_pkg_dir = Path(_nnunetv2_pkg.__file__).parent
_trainer_variants_dir = _nnunet_pkg_dir / "training" / "nnUNetTrainer" / "variants"
_trainer_file = _trainer_variants_dir / "nnUNetTrainer_250epochs_Modified.py"
_trainer_file.write_text(_MODIFIED_TRAINER_SRC, encoding="utf-8")

import importlib
_mod_name = "nnunetv2.training.nnUNetTrainer.variants.nnUNetTrainer_250epochs_Modified"
if _mod_name in importlib.sys.modules:
    importlib.reload(importlib.sys.modules[_mod_name])
_mod = importlib.import_module(_mod_name)
assert hasattr(_mod, "nnUNetTrainer_250epochs_Modified"), "Trainer nao registrado."

print(f"Trainer salvo em: {_trainer_file}")
print(f"Trainer registrado: {TRAINER}")
print("  1. GroupNorm (substitui InstanceNorm) -- via build_network_architecture")
print("  2. AxialAttention3D no decoder        -- via build_network_architecture")
print("  3. HD loss (warmup + subsampling)     -- via _build_loss")
print("  4. Encoder grande: planner ResEncL")

Trainer salvo em: /home/henrique.grande/.conda/envs/testes_mest_henrique/lib/python3.10/site-packages/nnunetv2/training/nnUNetTrainer/variants/nnUNetTrainer_250epochs_Modified.py
Trainer registrado: nnUNetTrainer_250epochs_Modified
  1. GroupNorm (substitui InstanceNorm) -- via build_network_architecture
  2. AxialAttention3D no decoder        -- via build_network_architecture
  3. HD loss (warmup + subsampling)     -- via _build_loss
  4. Encoder grande: planner ResEncL


In [5]:
def get_patient_ids(directory):
    if not directory.exists():
        return []
    return sorted([d.name for d in directory.iterdir() if d.is_dir()])

def find_file(folder, key):
    for cand in [folder / f"{key}.nii.gz", folder / f"{key}.nii"]:
        if cand.exists():
            return cand
    cands = sorted(list(folder.glob(f"*{key}*.nii*")))
    if key == "t1n":
        cands = [c for c in cands if "t1c" not in c.name.lower()]
    if not cands:
        raise FileNotFoundError(f"{key} not found in {folder}")
    return cands[0]

unlabeled_ids = get_patient_ids(UNLABELED_RAW)
print(f"Casos nao-rotulados: {len(unlabeled_ids)}")

Casos nao-rotulados: 1138


In [6]:
# Copia as 4 modalidades p/ o padrao nnU-Net (<caso>_0000 .. _0003)
for cid in tqdm(unlabeled_ids, desc="Export -> imagesUnlabeled"):
    d = UNLABELED_RAW / cid
    for ch, mod in enumerate(MODS):
        src = find_file(d, mod)
        dst = GEN_IMAGES / f"{cid}_{ch:04d}{FILE_ENDING}"
        if not dst.exists():
            shutil.copy2(src, dst)
print("Total imagesUnlabeled:", len(list(GEN_IMAGES.glob(f"*{FILE_ENDING}"))))

Export -> imagesUnlabeled:   0%|          | 0/1138 [00:00<?, ?it/s]

Export -> imagesUnlabeled:   0%|          | 2/1138 [00:00<00:57, 19.91it/s]

Export -> imagesUnlabeled:   0%|          | 5/1138 [00:00<00:57, 19.77it/s]

Export -> imagesUnlabeled:   1%|          | 8/1138 [00:00<00:55, 20.34it/s]

Export -> imagesUnlabeled:   1%|          | 11/1138 [00:00<00:49, 22.60it/s]

...

Export -> imagesUnlabeled:  99%|█████████▉| 1129/1138 [00:37<00:00, 21.85it/s]

Export -> imagesUnlabeled: 100%|█████████▉| 1133/1138 [00:37<00:00, 25.92it/s]

Export -> imagesUnlabeled: 100%|█████████▉| 1137/1138 [00:37<00:00, 27.67it/s]

Export -> imagesUnlabeled: 100%|██████████| 1138/1138 [00:37<00:00, 30.18it/s]

Total imagesUnlabeled: 4552


In [7]:
# Inferencia ENSEMBLE dos 5 folds (TTA ligado) + probabilidades p/ confianca
cmd = (
    f'nnUNetv2_predict -i "{GEN_IMAGES}" -o "{GEN_PRED}" -d {DATASET_ID} -c {CONFIG} '
    f'-f {FOLDS_STR} -p {PLANS_NAME} -tr {TRAINER} -chk {CHK} --save_probabilities'
)
get_ipython().system(cmd)
_n = len(list(GEN_PRED.glob(f"*{FILE_ENDING}")))
assert _n > 0, f"Nenhuma predicao em {GEN_PRED} - confira teacher treinado, trainer registrado e o log do predict."
print("Pseudo-mascaras geradas:", _n)


#######################################################################
Please cite the following paper when using nnU-Net:
Isensee, F., Jaeger, P. F., Kohl, S. A., Petersen, J., & Maier-Hein, K. H. (2021). nnU-Net: a self-configuring method for deep learning-based biomedical image segmentation. Nature methods, 18(2), 203-211.
#######################################################################



[Modified] build_network_architecture: GroupNorm=124 | AxialAttn_decoder=True


There are 1138 cases in the source folder
I am processing 0 out of 1 (max process ID is 0, we start counting with 0!)
There are 1138 cases that I would like to predict



Predicting BraTS-GoAT-00001:
perform_everything_on_device: True


  0%|                                                     | 0/8 [00:00<?, ?it/s]

...

100%|█████████████████████████████████████████████| 8/8 [00:03<00:00,  2.06it/s]


sending off prediction to background worker for resampling and export
done with BraTS-GoAT-02488


Exception ignored in: <Finalize object, dead>
Traceback (most recent call last):
  File "/home/henrique.grande/.conda/envs/testes_mest_henrique/lib/python3.10/multiprocessing/util.py", line 224, in __call__


    res = self._callback(*self._args, **self._kwargs)
  File "/home/henrique.grande/.conda/envs/testes_mest_henrique/lib/python3.10/multiprocessing/synchronize.py", line 87, in _cleanup
    sem_unlink(name)
FileNotFoundError: [Errno 2] No such file or directory
Exception ignored in: <Finalize object, dead>
Traceback (most recent call last):
  File "/home/henrique.grande/.conda/envs/testes_mest_henrique/lib/python3.10/multiprocessing/util.py", line 224, in __call__
    res = self._callback(*self._args, **self._kwargs)
  File "/home/henrique.grande/.conda/envs/testes_mest_henrique/lib/python3.10/multiprocessing/synchronize.py", line 87, in _cleanup
    sem_unlink(name)
FileNotFoundError: [Errno 2] No such file or directory
Exception ignored in: <Finalize object, dead>
Traceback (most recent call last):
  File "/home/henrique.grande/.conda/envs/testes_mest_henrique/lib/python3.10/multiprocessing/util.py", line 224, in __call__
    res = self._callback(*self._args, **self._kwargs)
  File "

Pseudo-mascaras geradas: 1138


In [8]:
# Confianca por caso a partir das probabilidades (.npz) - teacher REGION-BASED (sigmoids WT/TC/ET)
# Confianca = media das confiancas das REGIOES PRESENTES (WT/TC/ET); regiao vazia e ignorada.
REGIONS_CLASS_ORDER = [2, 1, 3]

def _load_probs(npz_path):
    data = np.load(npz_path)
    key = "probabilities" if "probabilities" in data.files else data.files[0]
    probs = data[key]
    data.close()
    return probs

def label_from_region_probs(probs, thr=0.5):
    lab = np.zeros(probs.shape[1:], dtype=np.int16)
    for ch, c in enumerate(REGIONS_CLASS_ORDER):
        lab[probs[ch] > thr] = c
    return lab

def case_confidence(npz_path):
    probs = _load_probs(npz_path)
    lab = label_from_region_probs(probs)
    wt = (lab == 1) | (lab == 2) | (lab == 3)   # canal 0 = whole_tumor
    tc = (lab == 1) | (lab == 3)                # canal 1 = tumor_core
    et = (lab == 3)                             # canal 2 = enhancing_tumor
    region_means = []
    for ch, m in [(0, wt), (1, tc), (2, et)]:
        if m.any():
            region_means.append(float(probs[ch][m].mean()))
    mean_conf = float(np.mean(region_means)) if region_means else 0.0
    return {
        "mean_fg_prob": round(mean_conf, 4),    # media das regioes presentes (WT/TC/ET)
        "vol_wt": int(wt.sum()),
        "vol_tc": int(tc.sum()),
        "vol_et": int(et.sum()),
        "empty": bool(int(wt.sum()) == 0),
    }

rows = []
for cid in tqdm(unlabeled_ids, desc="Confianca por caso"):
    npz = GEN_PRED / f"{cid}.npz"
    if not npz.exists():
        continue
    r = {"id": cid}
    r.update(case_confidence(npz))
    rows.append(r)

df_conf = pd.DataFrame(rows).sort_values("mean_fg_prob", ascending=False).reset_index(drop=True)
conf_csv = OUT_PSEUDO / "confidence.csv"
df_conf.to_csv(conf_csv, index=False)
print("CSV salvo:", conf_csv)
df_conf[["mean_fg_prob", "vol_wt", "vol_tc", "vol_et"]].describe().round(4)

Confianca por caso:   0%|          | 0/1138 [00:00<?, ?it/s]

Confianca por caso:   0%|          | 1/1138 [00:00<07:27,  2.54it/s]

Confianca por caso:   0%|          | 2/1138 [00:00<06:17,  3.01it/s]

Confianca por caso:   0%|          | 3/1138 [00:00<05:46,  3.28it/s]

Confianca por caso:   0%|          | 4/1138 [00:01<07:49,  2.41it/s]

...

Confianca por caso: 100%|█████████▉| 1137/1138 [05:51<00:00,  3.67it/s]

Confianca por caso: 100%|██████████| 1138/1138 [05:51<00:00,  3.70it/s]

Confianca por caso: 100%|██████████| 1138/1138 [05:51<00:00,  3.24it/s]

CSV salvo: /home/henrique.grande/brats_goat_experiments/data/raw/MICCAI2024-BraTS-GoAT-TrainingData-Without-GroundTruth-pseudolabeled/confidence.csv


,mean_fg_prob,vol_wt,vol_tc,vol_et
count,1138.0000,1138.0000,1138.0000,1138.0000
mean,0.9106,47560.2258,20047.8427,18503.9982
std,0.2345,63306.0001,28456.4584,26612.1570
min,0.0000,0.0000,0.0000,0.0000
25%,0.9690,2301.2500,1350.2500,1273.5000
50%,0.9822,16769.5000,7827.5000,7306.0000
75%,0.9874,72338.0000,27425.7500,24400.7500
max,0.9936,326299.0000,199435.0000,162310.0000


In [9]:
# Materializa TODOS os casos em OUT_PSEUDO/<caso>/ (4 modalidades + pseudo-seg).
made = 0
for cid in tqdm(unlabeled_ids, desc="Materializa pseudolabeled"):
    pred = GEN_PRED / f"{cid}.nii.gz"
    if not pred.exists():
        continue
    case_out = OUT_PSEUDO / cid
    case_out.mkdir(parents=True, exist_ok=True)
    src_dir = UNLABELED_RAW / cid
    for mod in MODS:
        s = find_file(src_dir, mod)
        shutil.copy2(s, case_out / s.name)
    shutil.copy2(pred, case_out / f"{cid}-seg.nii.gz")
    made += 1
print(f"Casos materializados em {OUT_PSEUDO}: {made}")

Materializa pseudolabeled:   0%|          | 0/1138 [00:00<?, ?it/s]

Materializa pseudolabeled:   0%|          | 2/1138 [00:00<00:57, 19.80it/s]

Materializa pseudolabeled:   0%|          | 5/1138 [00:00<00:53, 21.20it/s]

Materializa pseudolabeled:   1%|          | 8/1138 [00:00<00:55, 20.31it/s]

Materializa pseudolabeled:   1%|          | 11/1138 [00:00<00:54, 20.66it/s]

...

Materializa pseudolabeled:  99%|█████████▉| 1129/1138 [00:59<00:00, 23.18it/s]

Materializa pseudolabeled:  99%|█████████▉| 1132/1138 [01:00<00:00, 24.71it/s]

Materializa pseudolabeled: 100%|█████████▉| 1137/1138 [01:00<00:00, 30.07it/s]

Materializa pseudolabeled: 100%|██████████| 1138/1138 [01:00<00:00, 18.90it/s]

Casos materializados em /home/henrique.grande/brats_goat_experiments/data/raw/MICCAI2024-BraTS-GoAT-TrainingData-Without-GroundTruth-pseudolabeled: 1138


In [10]:
print("Resumo do gerador (teacher = Modified_nnUNet_submission, ensemble 5 folds, region-based):")
print(f"  Casos preditos          : {made}")
print(f"  mean_fg_prob medio      : {df_conf['mean_fg_prob'].mean():.4f}")
print(f"  Saida (consumida pelo SSL): {OUT_PSEUDO}")

Resumo do gerador (teacher = Modified_nnUNet_submission, ensemble 5 folds, region-based):
  Casos preditos          : 1138
  mean_fg_prob medio      : 0.9106
  Saida (consumida pelo SSL): /home/henrique.grande/brats_goat_experiments/data/raw/MICCAI2024-BraTS-GoAT-TrainingData-Without-GroundTruth-pseudolabeled
